In [9]:
import torch
from torch.distributed.checkpoint.format_utils import dcp_to_torch_save
import pprint
import plotly.graph_objects as go


### Functions

In [39]:
def extend_permutation(permute:torch.Tensor):
    R, C = permute.shape  # 5, 3

    # find zero rows
    zero_rows = (permute == 0).all(dim=1)
    zero_idx = torch.where(zero_rows)[0]

    # extend to square permutation matrix
    P = torch.zeros((R, R), dtype=permute.dtype)

    # copy existing columns
    P[:, :C] = permute

    # fill missing columns with identity on zero rows
    for k, i in enumerate(zero_idx):
        P[i, C + k] = 1

    return P

def permute(A:torch.Tensor, permute: torch.Tensor):
    permute = extend_permutation(permute)
    return A @ permute

def plotly_heatmap(t: torch.Tensor, plot_name: str="heatmap", width: int=1000):
    t_y, t_x = t.shape
    fig_w = width
    fig_h = fig_w * (t_y / t_x)

    fig = go.Figure(
        data=go.Heatmap(
            z=t.cpu().numpy(),
            colorscale="Viridis",
            colorbar=dict(title="Value"),
        )
    )

    fig.update_layout(
        title=f"{plot_name}",
        xaxis_title=f"Dimension {t_x}",
        yaxis_title=f"Dimension {t_y}",
        width=fig_w,
        height=fig_h,
        yaxis=dict(autorange="reversed")
    )

    fig.show()

def plot_agregate_rows(t: torch.Tensor):

    row_std = torch.std(t, dim=1)

    vals, idxs = torch.topk(row_std, k=5)

    print("indices:", idxs)
    print("values:", vals)

    x = list(range(t.shape[0]))

    fig = go.Figure()

    fig.add_trace(
        go.Scatter(
            x=x,
            y=row_std.cpu().numpy(),
            mode="lines",
            name="std per row",
        )
    )

    fig.update_layout(
        title=f"std per row",
        xaxis_title="Row index",
        yaxis_title="Value",
        hovermode="x unified",
    )

    fig.show()

def tprint(ckpt, tkey):
    # prints shape, min, max
    t = ckpt[tkey]
    print(f"{tkey}| shape: ({t.shape[0]}, {t.shape[1]}), range: ({t.min()}, {t.max()})")

def row_stats(t, k=5):
    row_mean = torch.mean(t, dim=1)
    row_max = torch.max(t, dim=1).values
    row_std = torch.std(t, dim=1)

    top_k_std_values, top_k_std_indices = torch.topk(row_std, k=k)
    
    return row_mean, row_max, row_std, top_k_std_indices

### make plots

#### calculate weights importances

In [11]:
dimension_importances_path = "/storage_nvme_3/mstefaniak/pc/fw_importances_8m/minitron_dimensions_importances.pt"
dim_imp_dict = torch.load(dimension_importances_path)['dmodel_importances']
pprint.pprint(dim_imp_dict)

tensor([6.2468e+07, 6.6452e+07, 1.0776e+08,  ..., 6.3428e+07, 8.5378e+07,
        6.1008e+07], device='cuda:0')


In [12]:
dimensions_importances = torch.load(dimension_importances_path)
dmodel_importances = dimensions_importances["dmodel_importances"]
dff_importances = dimensions_importances["dff_importances"]

dmodel_indices = torch.topk(
    dmodel_importances, dim=0, largest=True, k=960
).indices

weight = torch.zeros(2048, 960)
weight[dmodel_indices, torch.arange(960)] = 1
print(weight.shape)

torch.Size([2048, 960])


#### load model

convert distributed to normal .pt

In [13]:
# Define your paths
path_from_neptune = "/storage_nvme_3/mstefaniak/nano_checkpoints/tmp/81615/0/step_4095"

parts = path_from_neptune.strip("/").split("/")
last_three = parts[-3:]
name = "_".join(last_three) 

CKPT = f"/storage_nvme_3/j321m/pc_models/{name}.pt"
print(CKPT)


/storage_nvme_3/j321m/pc_models/81615_0_step_4095.pt


In [14]:
print(f"Converting DCP from: {path_from_neptune}")
print(f"Saving to: {CKPT}")

# Run the conversion
dcp_to_torch_save(path_from_neptune, CKPT)

print("Conversion complete.")

Converting DCP from: /storage_nvme_3/mstefaniak/nano_checkpoints/tmp/81615/0/step_4095
Saving to: /storage_nvme_3/j321m/pc_models/81615_0_step_4095.pt


Conversion complete.


load model

In [15]:
ckpt = torch.load(CKPT, map_location="cpu")['app']['model'] 

In [16]:
pprint.pprint(list(ckpt.keys()))                 # top-level keys
sd = ckpt.get("model", ckpt)       # depending on how it was saved
print(len(sd))
print(list(sd.keys())[:50]) 

['embedding.projection',
 'embedding.embedding.weight',
 'embedding.auxiliary_weight.weight',
 'encoder.blocks.0.attention_layer.norm.weight',
 'encoder.blocks.0.attention_layer.layer.q_proj.weight',
 'encoder.blocks.0.attention_layer.layer.q_proj.projection_in_weight',
 'encoder.blocks.0.attention_layer.layer.q_proj.auxiliary_weight',
 'encoder.blocks.0.attention_layer.layer.k_proj.weight',
 'encoder.blocks.0.attention_layer.layer.k_proj.projection_in_weight',
 'encoder.blocks.0.attention_layer.layer.k_proj.auxiliary_weight',
 'encoder.blocks.0.attention_layer.layer.v_proj.weight',
 'encoder.blocks.0.attention_layer.layer.v_proj.projection_in_weight',
 'encoder.blocks.0.attention_layer.layer.v_proj.auxiliary_weight',
 'encoder.blocks.0.attention_layer.layer.o_proj.weight',
 'encoder.blocks.0.attention_layer.layer.o_proj.projection_out_weight',
 'encoder.blocks.0.attention_layer.layer.o_proj.auxiliary_weight',
 'encoder.blocks.0.ff_layer.norm.weight',
 'encoder.blocks.0.ff_layer.layer.

#### plot

In [24]:
block_elems = [
    'encoder.blocks.1.attention_layer.norm.weight',
    'encoder.blocks.1.attention_layer.layer.q_proj.weight',
    'encoder.blocks.1.attention_layer.layer.q_proj.projection_in_weight',
    'encoder.blocks.1.attention_layer.layer.q_proj.auxiliary_weight',
    'encoder.blocks.1.attention_layer.layer.k_proj.weight',
    'encoder.blocks.1.attention_layer.layer.k_proj.projection_in_weight',
    'encoder.blocks.1.attention_layer.layer.k_proj.auxiliary_weight',
    'encoder.blocks.1.attention_layer.layer.v_proj.weight',
    'encoder.blocks.1.attention_layer.layer.v_proj.projection_in_weight',
    'encoder.blocks.1.attention_layer.layer.v_proj.auxiliary_weight',
    'encoder.blocks.1.attention_layer.layer.o_proj.weight',
    'encoder.blocks.1.attention_layer.layer.o_proj.projection_out_weight',
    'encoder.blocks.1.attention_layer.layer.o_proj.auxiliary_weight',
    'encoder.blocks.1.ff_layer.norm.weight',
    'encoder.blocks.1.ff_layer.layer.ff_pre_act.weight',
    'encoder.blocks.1.ff_layer.layer.ff_pre_act.projection_in_weight',
    'encoder.blocks.1.ff_layer.layer.ff_pre_act.projection_out_weight',
    'encoder.blocks.1.ff_layer.layer.ff_pre_act.auxiliary_weight',
    'encoder.blocks.1.ff_layer.layer.ff_post_act.weight',
    'encoder.blocks.1.ff_layer.layer.ff_post_act.projection_in_weight',
    'encoder.blocks.1.ff_layer.layer.ff_post_act.projection_out_weight',
    'encoder.blocks.1.ff_layer.layer.ff_post_act.auxiliary_weight',
    'encoder.blocks.1.ff_layer.layer.gate.weight',
    'encoder.blocks.1.ff_layer.layer.gate.projection_in_weight',
    'encoder.blocks.1.ff_layer.layer.gate.projection_out_weight',
    'encoder.blocks.1.ff_layer.layer.gate.auxiliary_weight',
]
block = 7

attn_v_in = f'encoder.blocks.{block}.attention_layer.layer.v_proj.projection_in_weight'
attn_o_out = f'encoder.blocks.{block}.attention_layer.layer.o_proj.projection_out_weight'

ff_pre_in = f'encoder.blocks.{block}.ff_layer.layer.ff_pre_act.projection_in_weight'
ff_pre_out = f'encoder.blocks.{block}.ff_layer.layer.ff_pre_act.projection_out_weight'

ff_post_in = f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.projection_in_weight'
ff_post_out = f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.projection_out_weight'

ff_gate_in = f'encoder.blocks.{block}.ff_layer.layer.gate.projection_in_weight'
ff_gate_out = f'encoder.blocks.{block}.ff_layer.layer.gate.projection_out_weight'


#### FF out

In [41]:
results = {}
all_top_indices = []
keyword = f'encoder.blocks.0.ff_layer.layer.ff_post_act.projection_out_weight'

avg_w = torch.zeros_like(ckpt[keyword])
for i in range(16):
    keyword = f'encoder.blocks.{i}.ff_layer.layer.ff_post_act.projection_out_weight'
    t = ckpt[keyword] - weight.T
    avg_w += t
    mean, max_val, std, top_indices = row_stats(t, k=5)
    
    results[f'weight_{i}'] = {
        'stats': (mean, max_val, std),
        'important_channels': top_indices
    }
    all_top_indices.append(top_indices)
    
    print(f"Weight {i} - Top 5 most active channels (by Std): {top_indices.tolist()}")

avg_w /= 16

Weight 0 - Top 5 most active channels (by Std): [13, 84, 1, 127, 40]
Weight 1 - Top 5 most active channels (by Std): [13, 84, 1, 40, 127]
Weight 2 - Top 5 most active channels (by Std): [1, 84, 13, 40, 10]
Weight 3 - Top 5 most active channels (by Std): [1, 84, 13, 8, 21]
Weight 4 - Top 5 most active channels (by Std): [1, 84, 13, 8, 886]
Weight 5 - Top 5 most active channels (by Std): [1, 84, 13, 244, 574]
Weight 6 - Top 5 most active channels (by Std): [1, 84, 13, 756, 8]
Weight 7 - Top 5 most active channels (by Std): [1, 84, 13, 833, 299]
Weight 8 - Top 5 most active channels (by Std): [1, 84, 13, 289, 299]
Weight 9 - Top 5 most active channels (by Std): [1, 13, 84, 299, 591]
Weight 10 - Top 5 most active channels (by Std): [1, 299, 13, 289, 591]
Weight 11 - Top 5 most active channels (by Std): [1, 299, 277, 13, 289]
Weight 12 - Top 5 most active channels (by Std): [1, 299, 277, 84, 591]
Weight 13 - Top 5 most active channels (by Std): [1, 13, 299, 84, 277]
Weight 14 - Top 5 most a

In [42]:
all_top_indices = torch.cat(all_top_indices)
num_channels = weight[0].shape[0]

# minlength ensures we get a count for EVERY channel from 0 to num_channels-1
channel_counts = torch.bincount(all_top_indices, minlength=num_channels)

# Prepare data for Plotly (No filtering)
x_indices = torch.arange(num_channels).numpy()
y_counts = channel_counts.numpy()

# --- Plotly Visualization ---

fig = go.Figure(data=[
    go.Bar(
        x=x_indices,
        y=y_counts,
        marker=dict(
            color=y_counts,            
            colorscale='Viridis',      
            showscale=True,
            colorbar=dict(title="Count")
        ),
        hovertemplate='<b>Channel:</b> %{x}<br><b>Count:</b> %{y}<extra></extra>'
    )
])

fig.update_layout(
    title='Histogram: Top-10 Frequency per Channel (All Channels)',
    xaxis_title='Channel Index',
    yaxis_title='Occurrences (across 5 weights)',
    yaxis=dict(tickmode='linear', tick0=0, dtick=1), # Integers only
    bargap=0, # Remove gaps between bars to make it look like a dense signal
    template='plotly_dark'
)

fig.show()

In [43]:
plot_agregate_rows(avg_w)

indices: tensor([ 1, 13, 84, 48, 97])
values: tensor([0.0026, 0.0023, 0.0020, 0.0014, 0.0014])


#### Attn out

In [44]:
results = {}
all_top_indices = []
keyword = f'encoder.blocks.0.attention_layer.layer.o_proj.projection_out_weight'

avg_w = torch.zeros_like(ckpt[keyword])
for i in range(16):
    keyword = f'encoder.blocks.{i}.attention_layer.layer.o_proj.projection_out_weight'
    t = ckpt[keyword] - weight.T
    avg_w += t
    mean, max_val, std, top_indices = row_stats(t, k=5)
    
    results[f'weight_{i}'] = {
        'stats': (mean, max_val, std),
        'important_channels': top_indices
    }
    all_top_indices.append(top_indices)
    
    print(f"Weight {i} - Top 5 most active channels (by Std): {top_indices.tolist()}")

avg_w /= 16

Weight 0 - Top 5 most active channels (by Std): [13, 1, 4, 32, 52]
Weight 1 - Top 5 most active channels (by Std): [13, 1, 84, 40, 16]
Weight 2 - Top 5 most active channels (by Std): [13, 1, 84, 818, 0]
Weight 3 - Top 5 most active channels (by Std): [13, 1, 679, 84, 932]
Weight 4 - Top 5 most active channels (by Std): [13, 1, 11, 422, 631]
Weight 5 - Top 5 most active channels (by Std): [13, 11, 1, 29, 35]
Weight 6 - Top 5 most active channels (by Std): [13, 1, 11, 5, 27]
Weight 7 - Top 5 most active channels (by Std): [1, 11, 17, 12, 35]
Weight 8 - Top 5 most active channels (by Std): [1, 11, 947, 13, 35]
Weight 9 - Top 5 most active channels (by Std): [1, 11, 13, 422, 299]
Weight 10 - Top 5 most active channels (by Std): [1, 56, 11, 35, 13]
Weight 11 - Top 5 most active channels (by Std): [1, 608, 514, 619, 891]
Weight 12 - Top 5 most active channels (by Std): [1, 84, 299, 886, 958]
Weight 13 - Top 5 most active channels (by Std): [1, 619, 679, 299, 958]
Weight 14 - Top 5 most activ

In [45]:
all_top_indices = torch.cat(all_top_indices)
num_channels = weight[0].shape[0]

# minlength ensures we get a count for EVERY channel from 0 to num_channels-1
channel_counts = torch.bincount(all_top_indices, minlength=num_channels)

# Prepare data for Plotly (No filtering)
x_indices = torch.arange(num_channels).numpy()
y_counts = channel_counts.numpy()

# --- Plotly Visualization ---

fig = go.Figure(data=[
    go.Bar(
        x=x_indices,
        y=y_counts,
        marker=dict(
            color=y_counts,            
            colorscale='Viridis',      
            showscale=True,
            colorbar=dict(title="Count")
        ),
        hovertemplate='<b>Channel:</b> %{x}<br><b>Count:</b> %{y}<extra></extra>'
    )
])

fig.update_layout(
    title='Histogram: Top-10 Frequency per Channel (All Channels)',
    xaxis_title='Channel Index',
    yaxis_title='Occurrences (across 5 weights)',
    yaxis=dict(tickmode='linear', tick0=0, dtick=1), # Integers only
    bargap=0, # Remove gaps between bars to make it look like a dense signal
    template='plotly_dark'
)

fig.show()

In [46]:
plot_agregate_rows(avg_w)

indices: tensor([  1,  13,  11, 862, 947])
values: tensor([0.0024, 0.0021, 0.0015, 0.0015, 0.0014])


#### old

In [47]:
print(f"attn_v_in shape: {ckpt[attn_v_in].shape}")
print(f"attn_o_out shape: {ckpt[attn_o_out].shape}")
print(f"ff_pre_in shape: {ckpt[ff_pre_in].shape}")
# print(f"ff_pre_out shape: {ckpt[ff_pre_out].shape}")
# print(f"ff_post_in shape: {ckpt[ff_post_in].shape}")
print(f"ff_post_out shape: {ckpt[ff_post_out].shape}")
print(f"ff_gate_in shape: {ckpt[ff_gate_in].shape}")
# print(f"ff_gate_out shape: {ckpt[ff_gate_out].shape}")
print()
print(f"weight shape: {weight.shape}")

attn_v_in shape: torch.Size([2048, 960])
attn_o_out shape: torch.Size([960, 2048])
ff_pre_in shape: torch.Size([2048, 960])
ff_post_out shape: torch.Size([960, 2048])
ff_gate_in shape: torch.Size([2048, 960])

weight shape: torch.Size([2048, 960])


In [ ]:
heatmap_target = [
    f'encoder.blocks.{block}.ff_layer.layer.ff_pre_act.projection_in_weight',
    # sum over blocks: 'encoder.blocks.{i}.ff_layer.layer.ff_pre_act.projection_in_weight'
    f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.projection_out_weight',
    # sum over blocks: 'encoder.blocks.{i}.ff_layer.layer.ff_post_act.projection_out_weight'
    f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.weight',
    f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.projection_in_weight',
    f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.projection_out_weight',
    f'encoder.blocks.{block}.ff_layer.layer.ff_post_act.auxiliary_weight',
]

In [18]:
for tkey in heatmap_target:
    tprint(ckpt, tkey)

encoder.blocks.7.ff_layer.layer.ff_pre_act.projection_in_weight| shape: (2048, 960), range: (-0.02433999627828598, 0.987158477306366)
encoder.blocks.7.ff_layer.layer.ff_post_act.projection_out_weight| shape: (960, 2048), range: (-0.023942936211824417, 0.9989869594573975)
encoder.blocks.7.ff_layer.layer.ff_post_act.weight| shape: (2048, 8192), range: (-0.484375, 0.46875)
encoder.blocks.7.ff_layer.layer.ff_post_act.projection_in_weight| shape: (8192, 3840), range: (-0.03820478916168213, 1.010326862335205)
encoder.blocks.7.ff_layer.layer.ff_post_act.projection_out_weight| shape: (960, 2048), range: (-0.023942936211824417, 0.9989869594573975)
encoder.blocks.7.ff_layer.layer.ff_post_act.auxiliary_weight| shape: (960, 3840), range: (-0.028805170208215714, 0.046656593680381775)


In [19]:
# plot block 0 projection_out_weight
t = ckpt[heatmap_target[1]] - weight.T

t = permute(t, weight)

plotly_heatmap(t, heatmap_target[1])

In [20]:
plot_agregate_rows(t)

indices: tensor([ 84,   1, 807, 631, 833])
values: tensor([0.0345, 0.0217, 0.0170, 0.0169, 0.0163])


In [21]:
w = ckpt[heatmap_target[2]]

w_sliced = w[:1000,:2000]

plotly_heatmap(w_sliced, heatmap_target[2])

In [22]:
w = ckpt[heatmap_target[5]]

# w_sliced = w[:1000,:2000]

plotly_heatmap(w_sliced, heatmap_target[5])

In [23]:
# python -m torch.distributed.checkpoint.format_utils dcp_to_torch \
#   /storage_nvme_3/mstefaniak/nano_checkpoints/tmp/81615/0/step_4095 \
#   /storage_nvme_3/j321m/pc_models/81615_0_step_4095_torchsave.pt
